In [ ]:
#import statements/setup
import numpy as np
from matplotlib import colormaps
import pandas as pd
from sklearn.metrics.pairwise import cosine_similarity
import plotly.express as px 
import statsmodels.stats.stattools as st

import os
os.environ["TOKENIZERS_PARALLELISM"] = "false"

from polysemy_visualization import compute_embeddings_for, make_sentence_snippets, draw_points, contextatlas

ModuleNotFoundError: No module named 'comp_tools'

In [ ]:
# global settings
modeltype = 'bert-base-uncased'

targetlemma = "draw"
inputfilename =  targetlemma + ".csv"
print(inputfilename)
print(os.getcwd())
print(os.listdir())

draw.csv
/Users/isaha/Desktop/research/prediction_comparison
['logistic_regression_prediction.ipynb', '__pycache__', 'polysemy_visualization.py', 'invite.csv', 'draw.csv', 'comp_tools.py']


## Fetching Embeddings

In [ ]:
df = pd.read_csv(inputfilename)
#df['sent'] = df['sent'].str.lower() 
#uncomment previous line if using csv prior to the fix, indicated in the shared spreadsheet
df.head(n=7) #to look at a few examples

,Unnamed: 0,tgt,subj,dobj,sent,meta_file,meta_indices
0,0,drew,that,it,""" Although the Covilles rode in a carriage , i...",text_fic_2015.txt,"(2257058, 2257257)"
1,1,draw,results,sufferers,<p> Researchers hope these promising results w...,text_mag_1991.txt,"(14868219, 14868377)"
2,2,draw,artist,thousands,May 20-21 . Summerville . Folk artist and his ...,text_news_2000.txt,"(12794015, 12794144)"
3,3,drawn,practice,criticism,@@4131396 Hundreds of migrants nabbed by the ...,text_news_2014.txt,"(12496474, 12496800)"
4,4,drawing,I,distinctions,"THOMPSON : If you 're watching these debates ,...",text_spok_2008.txt,"(5134407, 5134638)"
5,5,draw,liberals,line,I would dismiss those who say that moderate li...,text_web_24.txt,"(3251670, 3251803)"
6,6,draw,others,story,"economy Re : "" Migrants backers rally ; Bennet...",text_news_2010.txt,"(7334245, 7334366)"


In [ ]:
#for the verbs:
verb_embeddings = compute_embeddings_for(df, what = "tgt", modeltype = modeltype)


Loading weights:   0%|          | 0/199 [00:00<?, ?it/s]

In [ ]:
#and the subjects...
subj_embeddings = compute_embeddings_for(df, what = "subj", modeltype = modeltype)
# bad_row = None
# for idx, row in df.iterrows():
#   try:
#     # Convert single row back to a DataFrame if needed by the function
#     single_row_df = df.loc[[idx]]
#     compute_embeddings_for(
#         single_row_df, what="subj", modeltype=modeltype
#     )
#   except Exception as e:
#     print(f"Error at index {idx}: {e}")
#     bad_row = idx
#     break

# print(f"The bad row index is: {bad_row}")

Loading weights:   0%|          | 0/199 [00:00<?, ?it/s]

In [ ]:
#finally the objects
obj_embeddings = compute_embeddings_for(df, what = "dobj", modeltype = modeltype)

Loading weights:   0%|          | 0/199 [00:00<?, ?it/s]

In [ ]:
df['verb_embedding'] = list(np.array(verb_embeddings))
df['subj_embedding']= list(np.array(subj_embeddings))
df['dobj_embedding'] = list(np.array(obj_embeddings))

## Computing Similarities

In [ ]:
# get similarities for each pair and store in new df
def get_pairs(num):
    pairs = []
    for x in range(num):
        for y in range(x, num):
            if x!=y:
                pairs.append((x,y))
    return pairs

pairs = get_pairs(len(df))
rows = []
for (x,y) in pairs:
    xrow = df.iloc[x]
    yrow = df.iloc[y]
    obj_sim = cosine_similarity(xrow['dobj_embedding'].reshape(1,-1), yrow['dobj_embedding'].reshape(1,-1))[0][0]
    subj_sim = cosine_similarity(xrow['subj_embedding'].reshape(1,-1), yrow['subj_embedding'].reshape(1,-1))[0][0]
    tgt_sim = cosine_similarity(xrow['verb_embedding'].reshape(1,-1), yrow['verb_embedding'].reshape(1,-1))[0][0]
    row = {"pair": (x,y), "sent1": xrow['sent'], "sent2": yrow["sent"], "obj_similarity": obj_sim, "verb_similarity": tgt_sim, "subj_similarity": subj_sim}
    rows.append(row)
pairwise_df = pd.DataFrame(rows)
pairwise_df.head()





,pair,sent1,sent2,obj_similarity,verb_similarity,subj_similarity
0,"(0, 1)",""" Although the Covilles rode in a carriage , i...",<p> Researchers hope these promising results w...,0.216625,0.452348,0.273801
1,"(0, 2)",""" Although the Covilles rode in a carriage , i...",May 20-21 . Summerville . Folk artist and his ...,0.310116,0.486947,0.210822
2,"(0, 3)",""" Although the Covilles rode in a carriage , i...",@@4131396 Hundreds of migrants nabbed by the ...,0.235328,0.361183,0.214659
3,"(0, 4)",""" Although the Covilles rode in a carriage , i...","THOMPSON : If you 're watching these debates ,...",0.326877,0.449987,0.283561
4,"(0, 5)",""" Although the Covilles rode in a carriage , i...",I would dismiss those who say that moderate li...,0.303593,0.498972,0.229951


## R2, Slope, Other Stats, and Visualization

In [ ]:
#verb vs subj graph visualization (using plotly)
fig = px.scatter(pairwise_df, x="obj_similarity", y="verb_similarity", hover_data=['pair'],trendline="ols")
fig.show()


In [ ]:
results = px.get_trendline_results(fig)
results = results.iloc[0]["px_fit_results"]
rsq = results.rsquared
slope = results.params[1]
pval = results.pvalues[1]
pomni = st.omni_normtest(results.resid)[1]
jb = st.jarque_bera(results.resid)
aic = results.aic
print(results.summary())
print(f"R2 = {rsq}, slope = {slope}, p-value of slope = {pval}, prob(omnibus) = {pomni}, jarque-bera = {jb}, aic: {aic}")
#P-value on the slope, P(omnibus), JB, AICs

                            OLS Regression Results                            
Dep. Variable:                      y   R-squared:                       0.321
Model:                            OLS   Adj. R-squared:                  0.321
Method:                 Least Squares   F-statistic:                 3.709e+04
Date:                Mon, 19 Oct 2026   Prob (F-statistic):               0.00
Time:                        14:11:19   Log-Likelihood:                 90836.
No. Observations:               78606   AIC:                        -1.817e+05
Df Residuals:                   78604   BIC:                        -1.816e+05
Df Model:                           1                                         
Covariance Type:            nonrobust                                         
                 coef    std err          t      P>|t|      [0.025      0.975]
------------------------------------------------------------------------------
const          0.3016      0.001    316.537      0.0

In [ ]:
#verb vs obj graph visualization (using plotly)
fig = px.scatter(pairwise_df, x="subj_similarity", y="verb_similarity", hover_data=['pair'],trendline="ols")
fig.show()


In [ ]:
results = px.get_trendline_results(fig)
results = results.iloc[0]["px_fit_results"]
rsq = results.rsquared
slope = results.params[1]
pval = results.pvalues[1]
pomni = st.omni_normtest(results.resid)[1]
jb = st.jarque_bera(results.resid)
aic = results.aic
print(results.summary())
print(f"R2 = {rsq}, slope = {slope}, p-value of slope = {pval}, prob(omnibus) = {pomni}, jarque-bera = {jb}, aic: {aic}")
#P-value on the slope, P(omnibus), JB, AICs

                            OLS Regression Results                            
Dep. Variable:                      y   R-squared:                       0.128
Model:                            OLS   Adj. R-squared:                  0.128
Method:                 Least Squares   F-statistic:                 1.153e+04
Date:                Mon, 19 Oct 2026   Prob (F-statistic):               0.00
Time:                        14:11:21   Log-Likelihood:                 81027.
No. Observations:               78606   AIC:                        -1.620e+05
Df Residuals:                   78604   BIC:                        -1.620e+05
Df Model:                           1                                         
Covariance Type:            nonrobust                                         
                 coef    std err          t      P>|t|      [0.025      0.975]
------------------------------------------------------------------------------
const          0.3774      0.001    384.104      0.0